# 02 · Benchmark, all folds

DL models vs the nine signal-processing estimators, pooled over the cross-validation folds that have
finished: every patient is scored once, by models that never saw them. Every comparison uses the same
windows (every test window scored by `scripts/benchmark_traditional.py`). Runs that have not
finished are skipped; re-run `bash scripts/build_report.sh` to refresh.

In [1]:
import sys, os, json
from pathlib import Path
ROOT = Path.cwd() if (Path.cwd() / "estimate_rr").exists() else Path.cwd().parent
os.chdir(ROOT); sys.path.insert(0, str(ROOT))

import numpy as np, pandas as pd
import plotly.graph_objects as go
from plotly.subplots import make_subplots
from IPython.display import HTML, display
import matplotlib.pyplot as plt

from common.metrics import rr_metrics
from scripts.make_report import comparison_table, best_traditional, stratified, RANGES, RATIOS, DL_KINDS

DATA, RUNS = Path("dataset/01NVa_monitor"), Path("runs")
FOLDS = [int(f) for f in os.environ.get("REPORT_FOLDS", "0 1 2 3 4").split()]   # pooled; folds that have not finished are left out
BLUE, ORANGE, AQUA, GRAY, INK2 = "#2a78d6", "#eb6834", "#1baf7a", "#c3c2b7", "#52514e"
_plotly_js_embedded = False

def show(fig, height=None):
    """Render a plotly figure with plotly.js embedded once, so the exported HTML works offline."""
    global _plotly_js_embedded
    fig.update_layout(template="simple_white", height=height, margin=dict(l=50, r=20, t=50, b=40),
                      font=dict(family="system-ui, sans-serif", size=12))
    display(HTML(fig.to_html(include_plotlyjs=not _plotly_js_embedded, full_html=False)))
    _plotly_js_embedded = True

windows = pd.read_parquet(DATA / "windows_w60_s30.parquet")
results = {}
for sig in ("ppg", "ecg"):
    t, df = comparison_table(sig, FOLDS, windows)
    if t is None or "dl_mod" not in df:
        print(f"{sig.upper()}: not finished yet, skipped")
        continue
    trad = best_traditional(df, "smart") or best_traditional(df, "median")
    results[sig] = dict(table=t, df=df.assign(ratio=df.ref_rr / df.hr), trad=trad,
                        trad_label=t.loc[t.column == trad, "estimator"].iloc[0])
    print(f"{sig.upper()}: folds {sorted(int(k) for k in df.fold.unique())}, {len(df):,} windows, {df.patient_id.nunique()} test patients; best signal-processing = {results[sig]['trad_label']}")

PPG: folds [0, 1, 2, 3, 4], 212,391 windows, 240 test patients; best signal-processing = ARM · smart fusion


ECG: folds [0, 1, 2, 3, 4], 289,552 windows, 240 test patients; best signal-processing = ARM · smart fusion


## All estimators

Sorted by MAE. Coverage < 100 % means the method rejected some windows (smart fusion).

In [2]:
cols = ["estimator", "coverage", "mae", "patient_macro_mae", "bias", "loa_low", "loa_high", "within_2bpm", "pearson_r"]
for sig, r in results.items():
    display(HTML(f"<h3>{sig.upper()}</h3>"))
    display(r["table"][[c for c in cols if c in r["table"]]].sort_values("mae").style
            .format({"coverage": "{:.0%}", "within_2bpm": "{:.0%}", "mae": "{:.2f}", "patient_macro_mae": "{:.2f}",
                     "bias": "{:+.2f}", "loa_low": "{:.1f}", "loa_high": "{:.1f}", "pearson_r": "{:.2f}"}, na_rep="—")
            .hide(axis="index"))

estimator,coverage,mae,patient_macro_mae,bias,loa_low,loa_high,within_2bpm,pearson_r
DL CNN · BW/AM/FM spectrogram,100%,0.88,1.23,-0.01,-3.4,3.4,90%,0.96
ARM · smart fusion,68%,1.27,1.77,+0.46,-4.0,4.9,82%,0.92
WCH · smart fusion,70%,1.41,2.04,+0.71,-4.0,5.4,78%,0.91
FTS · smart fusion,68%,1.49,2.07,+0.66,-4.4,5.7,77%,0.89
ARS · smart fusion,66%,1.82,2.44,+0.74,-5.3,6.8,71%,0.83
ARP · smart fusion,66%,1.87,2.49,+0.71,-5.5,6.9,70%,0.82
ARM · median fusion,100%,1.92,2.45,+0.90,-6.8,8.6,78%,0.78
CtO · smart fusion,80%,1.96,2.42,-0.45,-6.0,5.1,64%,0.86
CtO · median fusion,100%,2.01,2.44,-0.52,-6.8,5.8,67%,0.84
WCH · median fusion,100%,2.08,2.62,+1.24,-6.6,9.1,75%,0.77


estimator,coverage,mae,patient_macro_mae,bias,loa_low,loa_high,within_2bpm,pearson_r
DL CNN · BW/AM/FM spectrogram,100%,0.99,1.23,+0.02,-4.1,4.1,89%,0.93
ARM · smart fusion,74%,1.30,1.63,+0.56,-4.4,5.5,82%,0.89
WCH · smart fusion,78%,1.38,1.80,+0.69,-4.2,5.6,80%,0.89
FTS · smart fusion,76%,1.46,1.84,+0.62,-4.5,5.8,79%,0.88
ARS · smart fusion,73%,1.80,2.31,+0.77,-5.4,6.9,73%,0.79
CtO · smart fusion,81%,1.81,2.06,-0.29,-5.9,5.3,70%,0.85
ARP · smart fusion,73%,1.84,2.37,+0.73,-5.5,7.0,71%,0.78
WCH · median fusion,100%,1.94,2.31,+0.94,-6.5,8.4,76%,0.78
ARM · median fusion,100%,1.95,2.25,+0.71,-7.1,8.6,77%,0.76
CtO · median fusion,100%,1.96,2.14,-0.50,-6.9,6.0,70%,0.83


## Bland–Altman

Hover a point for the patient and window; the diagonal streaks are runs of windows with a near-constant reference (see notebook 01, possible ventilation).

In [3]:
for sig, r in results.items():
    df = r["df"]
    fig = make_subplots(1, 2, shared_yaxes=True, subplot_titles=(DL_KINDS["mod"], r["trad_label"]))
    for i, (col, color) in enumerate([("dl_mod", BLUE), (r["trad"], ORANGE)], start=1):
        d = df[df[col].notna()]
        mean, diff = (d[col] + d.ref_rr) / 2, d[col] - d.ref_rr
        b, sd = diff.mean(), diff.std()                       # statistics on every window
        if len(d) > 25_000:                                   # drawn points: a random 25k, so the page stays light
            d = d.sample(25_000, random_state=0); mean, diff = (d[col] + d.ref_rr) / 2, d[col] - d.ref_rr
        fig.add_trace(go.Scattergl(x=mean, y=diff, mode="markers", marker=dict(size=3, color=color, opacity=0.3),
                                   customdata=np.c_[d.patient_id, d.start_s, d.ref_rr, d[col]], showlegend=False,
                                   hovertemplate="%{customdata[0]} @ %{customdata[1]:.0f} s<br>ref %{customdata[2]:.1f}, "
                                                 "estimate %{customdata[3]:.1f}<extra></extra>"), 1, i)
        for v, dash in ((b, "solid"), (b - 1.96 * sd, "dash"), (b + 1.96 * sd, "dash")):
            fig.add_hline(y=v, line_dash=dash, line_color=INK2, line_width=1, row=1, col=i)
    fig.update_yaxes(range=[-20, 20], title_text="estimate − reference (bpm)", row=1, col=1)
    fig.update_xaxes(title_text="mean of estimate and reference (bpm)")
    fig.update_layout(title=f"{sig.upper()} Bland–Altman, held-out patients (lines from all windows; up to 25,000 points drawn per panel)")
    show(fig, 430)

## Per-patient error

Each bar is one test patient; MAE over that patient's windows. Patients are sorted by the DL error.

In [4]:
for sig, r in results.items():
    df = r["df"]
    g = df.groupby("patient_id").apply(lambda d: pd.Series({
        "windows": len(d), "dl": (d.dl_mod - d.ref_rr).abs().mean(),
        "trad": (d[r["trad"]] - d.ref_rr).abs().mean(), "ref_median": d.ref_rr.median()}), include_groups=False).sort_values("dl")
    fig = go.Figure([
        go.Bar(x=g.index, y=g.dl, name=DL_KINDS["mod"], marker_color=BLUE,
               customdata=np.c_[g.windows, g.ref_median], hovertemplate="%{x}<br>MAE %{y:.2f} · %{customdata[0]} windows · median ref %{customdata[1]:.1f}<extra></extra>"),
        go.Bar(x=g.index, y=g.trad, name=r["trad_label"], marker_color=ORANGE)])
    fig.update_layout(title=f"{sig.upper()}: MAE per test patient", yaxis_title="MAE (bpm)", barmode="group",
                      xaxis=dict(showticklabels=False, title="test patients"), legend=dict(orientation="h", y=1.08))
    show(fig, 380)
    print(f"DL better than {r['trad_label']} for {(g.dl < g.trad).mean():.0%} of patients")

DL better than ARM · smart fusion for 92% of patients


DL better than ARM · smart fusion for 85% of patients


## Where the errors are

MAE by reference-RR range and by RR/HR ratio. The ratio panel shows the beat-sampling limit: signal-processing error climbs as RR approaches HR/2.

In [5]:
for sig, r in results.items():
    df = r["df"]
    series = [("dl_mod", DL_KINDS["mod"], BLUE)] + ([("dl_raw", DL_KINDS["raw"], AQUA)] if "dl_raw" in df else []) + [(r["trad"], r["trad_label"], ORANGE)]
    fig = make_subplots(1, 2, subplot_titles=("by reference RR (bpm)", "by RR / HR ratio"))
    for col, label, color in series:
        for i, (by, edges) in enumerate([("ref_rr", RANGES), ("ratio", RATIOS)], start=1):
            s = stratified(df, col, by, edges)
            fig.add_trace(go.Bar(x=[f"{b}<br>n={n}" for b, n in zip(s.bin, s.n)], y=s.mae, name=label, marker_color=color,
                                 showlegend=(i == 1), hovertemplate=label + ": MAE %{y:.2f}<extra></extra>"), 1, i)
    fig.update_yaxes(title_text="MAE (bpm)", row=1, col=1)
    fig.update_layout(title=f"{sig.upper()}: MAE by stratum", barmode="group", legend=dict(orientation="h", y=-0.25, x=0))
    show(fig, 440)

## Why the published spectral methods fail here

FTS, WCH, ARS, ARM and ARP, as published, take the strongest spectral peak in 4–60 breaths/min. In this
cohort that peak is often a very-low-frequency component (< 8 breaths/min) rather than breathing, so they
under-estimate. The corrected rule (the default) takes the peak standing highest above a fitted 1/f
background instead. CtO counts individual breaths and needs no correction.

In [6]:
for sig, r in results.items():
    df = r["df"]
    fig = go.Figure()
    edges = np.arange(0, 61, 1.0)
    for col, label, color, alpha in [("welch|pub-median", "WCH as published", GRAY, 0.55), ("welch|median", "WCH corrected", BLUE, 0.55),
                                     ("count_orig|median", "CtO", AQUA, 0.55), ("ref_rr", "reference", INK2, 0.45)]:
        if col in df:
            n, _ = np.histogram(df[col].dropna(), bins=edges)
            fig.add_trace(go.Bar(x=edges[:-1] + 0.5, y=n, name=label, marker_color=color, opacity=alpha, width=1))
    fig.update_layout(title=f"{sig.upper()}: estimates vs reference distribution (median fusion)", barmode="overlay",
                      xaxis_title="breaths/min", yaxis_title="windows", legend=dict(orientation="h", y=1.1))
    show(fig, 360)
    if "welch|pub-median" in df:
        print(f"{sig.upper()}: below 8 breaths/min in {(df['welch|pub-median'] < 8).mean():.0%} of windows for WCH as published, "
              f"{(df['welch|median'] < 8).mean():.0%} corrected, {(df.ref_rr < 8).mean():.2%} for the reference")

PPG: below 8 breaths/min in 39% of windows for WCH as published, 0% corrected, 0.01% for the reference


ECG: below 8 breaths/min in 17% of windows for WCH as published, 0% corrected, 0.01% for the reference


## Training curves (fold 0)

Solid lines are the CNN, dashed lines the transformer (frame tokens) on the same input.

In [7]:
fig = go.Figure()
# solid = CNN, dashed = transformer (frame tokens); same colour = same input
for run, color in [("ppg_mod_w60", BLUE), ("ppg_raw_w60", AQUA), ("ecg_mod_w60", ORANGE), ("ecg_raw_w60", "#6250d6")]:
    for tag, dash, arch in (("", "solid", "CNN"), ("_tf-frame", "dash", "transformer")):
        h = RUNS / f"{run}{tag}_f0" / "history.csv"
        if h.exists():
            h = pd.read_csv(h)
            fig.add_trace(go.Scatter(x=h.epoch, y=h.val_patient_mae, name=f"{run} {arch}",
                                     line=dict(color=color, width=2, dash=dash)))
fig.update_layout(title="Validation per-patient MAE by epoch (model selection metric)", xaxis_title="epoch",
                  yaxis_title="MAE (bpm)", legend=dict(orientation="h", y=1.15))
show(fig, 380)

## Worst DL windows

The three largest DL errors, drawn the way the model sees them: the impedance reference, the input
signal, the derived BW/AM/FM signals and the three spectrogram channels (orange line = reference).

In [8]:
from data_prep.build_dataset import TARGET_FS
from dl.features import SpecConfig, modulation_spectrogram
from estimate_rr.resp_signals import RESP_FS, extract_resp_signals, respiratory_waveform

def view_window(row, sig, preds):
    data = np.load(DATA / "signals" / f"{row.segment_id}.npz")
    cut = {k: data[k][int(row.start_s * fs):int((row.start_s + 60) * fs)].astype(float) for k, fs in TARGET_FS.items()}
    fig = plt.figure(figsize=(12, 6.5))
    gs = fig.add_gridspec(4, 3)
    ax = fig.add_subplot(gs[0, :]); y = respiratory_waveform(cut["resp"], TARGET_FS["resp"])
    ax.plot(np.arange(len(y)) / RESP_FS, y, color=INK2); ax.set_yticks([])
    ax.set_title(f"{row.patient_id} @ {row.start_s:.0f} s · reference {row.ref_rr:.1f} · " + " · ".join(f"{k} {v:.1f}" for k, v in preds.items()), loc="left", fontsize=10)
    ax = fig.add_subplot(gs[1, :]); ax.plot(np.arange(len(cut[sig])) / TARGET_FS[sig], cut[sig], color=INK2, lw=0.6); ax.set_yticks([])
    ax = fig.add_subplot(gs[2, :]); rs = extract_resp_signals(cut[sig], TARGET_FS[sig], sig)
    for name, color in (("bw", BLUE), ("am", ORANGE), ("fm", AQUA)):
        if name in rs.signals:
            s = rs.signals[name]; ax.plot(np.arange(len(s)) / RESP_FS, s / s.std(), color=color, label=name.upper(), lw=1.2)
    ax.legend(ncol=3, fontsize=8, loc="upper right"); ax.set_yticks([])
    spec, cfg = modulation_spectrogram(cut[sig], TARGET_FS[sig], sig), SpecConfig()
    for i, name in enumerate(("BW", "AM", "FM")):
        ax = fig.add_subplot(gs[3, i])
        if spec is not None:
            ax.imshow(spec[i], aspect="auto", origin="lower", cmap="Blues", extent=[0, spec.shape[2], cfg.band_low_hz * 60, cfg.band_high_hz * 60])
            ax.axhline(row.ref_rr, color=ORANGE, lw=1)
        ax.set_title(name, fontsize=9, loc="left")
    fig.tight_layout(); plt.show()

for sig, r in results.items():
    df = r["df"].assign(err=lambda d: (d.dl_mod - d.ref_rr).abs())
    for _, row in df.nlargest(3, "err").iterrows():
        view_window(row, sig, {"DL": row["dl_mod"], r["trad_label"]: row[r["trad"]]})